In [ ]:
# =========================
# 0) Fill these paths (필수)
# =========================
VAE_CONFIG = "autoencoder_kl_64x64x3.yaml"  # e.g., "/path/to/autoencoder_kl.yaml"
VAE_CKPT   = "ae_model.ckpt"  # e.g., "/path/to/autoencoder_kl.ckpt"
UNET_CKPT  = "ldm_model.ckpt"  # e.g., "/path/to/ldm_unet.ckpt"

In [8]:
# -*- coding: utf-8 -*-
"""
CT→MRI(b0) Coarse LDM — single cell (Jupyter-ready)
- STRICT_PRETRAIN=False (기본): CFG 기반 UNet 생성 + 프리트레인 ckpt 부분로드(입/출 채널 최소치 슬라이싱)
- 데이터: 환자단위(patient-wise) 재귀 탐색 + 폴더명으로 CT/MR 식별 + jpg/png/jpeg/tif/tiff 지원 + 번호 정렬 매칭
- 안정화: 해상도 정렬, 입력 채널 어댑터, 출력 채널 어댑터, 샘플링 z→VAE 채널 어댑터

필수 경로(아래에 채우기):
  VAE_CONFIG = "/path/to/autoencoder_kl.yaml"
  VAE_CKPT   = "/path/to/autoencoder_kl.ckpt"
  UNET_CKPT  = "/path/to/ldm_unet.ckpt"
"""

# =========================
# 0) 경로/플래그
# =========================
VAE_CONFIG = "autoencoder_kl_64x64x3.yaml"  # e.g., "/path/to/autoencoder_kl.yaml"
VAE_CKPT   = "ae_model.ckpt"  # e.g., "/path/to/autoencoder_kl.ckpt"
UNET_CKPT  = "ldm_model.ckpt"  # e.g., "/path/to/ldm_unet.ckpt"

STRICT_PRETRAIN = False  # 권장: False (설치 의존/구조불일치 이슈 회피)

# =========================
# 1) Imports & utils
# =========================
import os, time, glob, random, math, warnings, re
from dataclasses import dataclass
from typing import Optional, List, Tuple, Dict

import numpy as np
from PIL import Image

import torch
import torch.nn as nn
import torch.nn.functional as F
from torch.utils.data import Dataset, DataLoader
from torchvision import transforms as T

def set_seed(seed: int):
    random.seed(seed); np.random.seed(seed); torch.manual_seed(seed); torch.cuda.manual_seed_all(seed)

def to_image_from_m11(x: torch.Tensor) -> Image.Image:
    x = x.detach().float()
    if x.dim() == 3:
        x = x.mean(0) if x.size(0) > 1 else x[0]
    x = (x.clamp(-1,1) + 1.0) * 0.5
    x = (x * 255.0 + 0.5).clamp(0,255).byte().cpu().numpy()
    return Image.fromarray(x, mode="L")

def save_triptych(ct_m11: torch.Tensor, pred_m11: torch.Tensor, gt_path: Optional[str], out_path: str, size: int):
    ct_img  = to_image_from_m11(ct_m11)
    pred_img= to_image_from_m11(pred_m11)
    if gt_path is not None and os.path.isfile(gt_path):
        gt_img = Image.open(gt_path).convert("L").resize((size,size), Image.BICUBIC)
    else:
        gt_img = Image.new("L", (size,size), color=0)
    panel = Image.new("L", (size*3, size), color=0)
    panel.paste(ct_img, (0,0)); panel.paste(pred_img, (size,0)); panel.paste(gt_img, (size*2,0))
    panel.save(out_path)

def stem(path: str) -> str:
    import os
    return os.path.splitext(os.path.basename(path))[0]

# =========================
# 2) Config (EXACT structure)
# =========================
CFG = {
    "seed": 42,
    "device": "cuda" if torch.cuda.is_available() else "cpu",

    # ===== 데이터 루트 (학습용) =====
    "data_root": "/data/ct-mri/dataset/processed_final_5",
    "use_groups": ["bleed", "non_bleed"],
    "ct_dir_candidates": ["ct_axial", "ct", "ct_png", "ctjpg", "ctjpeg"],
    "mri_b0_dir_candidates": ["mri_b0_axial", "mri_b0", "b0", "dwi_b0", "dwi", "dwi_axial_b0"],
    "ct_file_globs": ["*ct*.jpg", "*CT*.jpg", "*ct*.png", "*CT*.png", "*ct*.jpeg", "*CT*.jpeg", "*ct*.tif", "*CT*.tif", "*ct*.tiff", "*CT*.tiff"],
    "mri_b0_file_globs": ["*b0*.jpg", "*B0*.jpg", "*dwi*.jpg", "*DWI*.jpg",
                          "*b0*.png", "*B0*.png", "*dwi*.png", "*DWI*.png",
                          "*b0*.jpeg", "*B0*.jpeg", "*dwi*.jpeg", "*DWI*.jpeg",
                          "*b0*.tif", "*B0*.tif", "*dwi*.tif", "*DWI*.tif",
                          "*b0*.tiff", "*B0*.tiff", "*dwi*.tiff", "*DWI*.tiff"],

    # ===== 학습 하이퍼 =====
    "img_size": 256,
    "batch_size": 8,
    "num_workers": 4,
    "epochs": 50,
    "lr": 2e-4,
    "ema_decay": 0.999,

    # ===== 확산 스케줄 =====
    "num_timesteps": 1000,
    "beta_schedule": "cosine",
    "ddim_steps": 200,
    "ddim_eta": 0.0,

    # ===== VAE =====
    "vae": {
        "scale": 0.18215,
        "ckpt": None,
        "eval_mode": True,
        "freeze": True
    },

    # ===== Latent U-Net =====
    "latent_unet": {
        "z_channels": 4,               # VAE z채널이 3이면 3으로 맞추면 더 깔끔 (지금은 어댑터로 안전 동작)
        "cond_channels": 1,            # CT latent 채널 수
        "model_channels": 192,
        "num_res_blocks": 2,
        "channel_mult": (1,2,3,4),
        "attention_resolutions": (16,),
        "num_heads": -1,
        "num_head_channels": 64,
        "num_heads_upsample": -1,
        "dropout": 0.1,
        "use_checkpoint": False,
        "use_fp16": False,
        "use_scale_shift_norm": True,
        "resblock_updown": False,
        "use_new_attention_order": False,
        "use_spatial_transformer": False,
        "transformer_depth": 1,
        "context_dim": None,
        "n_embed": None,
        "legacy": True,
    },

    # ===== 보조 손실 옵션 =====
    "aux_losses": {
        "use_tv": True,
        "tv_weight": 1e-5,
        "use_lpips": False,
        "lpips_weight": 0.05
    },

    # ===== 체크포인트 =====
    "save_dir": "./runs_ldm_coarse2",
    "resume": None,

    # ===== 에폭별 CT-only inference =====
    "inference": {
        "enabled": True,
        "num_examples": 8,
        "sampler": "ddim",
        "ddim_steps": 200,
        "eta": 0.0,
        "seed": 1234,
        "ct_list": [],
        "ct_glob": None,
        "out_subdir": "epoch_infer_ldm",
        "write_mapping": True
    }
}

# =========================
# 3) Data scanning (patient-wise)
# =========================
IMG_EXTS = (".png", ".jpg", ".jpeg", ".bmp", ".tif", ".tiff")

def _list_subdirs(path: str) -> List[str]:
    try:
        return [os.path.join(path, d) for d in os.listdir(path) if os.path.isdir(os.path.join(path, d))]
    except FileNotFoundError:
        return []

def _rglob_images(root: str) -> List[str]:
    files = []
    for ext in IMG_EXTS:
        files.extend(glob.glob(os.path.join(root, "**", f"*{ext}"), recursive=True))
    return sorted(set(files))

def _find_modality_dirs_patientwise(patient_dir: str) -> Tuple[Optional[str], Optional[str]]:
    ct_cand, mr_cand = None, None
    for cur, dirs, _ in os.walk(patient_dir):
        base = os.path.basename(cur).lower()
        if re.search(r'(^|[_\-/])ct([_\-/]|$)', base):
            ct_cand = cur
        if re.search(r'(^|[_\-/])(mri|b0|dwi)([_\-/]|$)', base):
            mr_cand = cur
    return ct_cand, mr_cand

def build_pairs_from_root(cfg: Dict) -> List[Tuple[str,str]]:
    root = cfg["data_root"]
    groups = cfg["use_groups"]
    pairs = []
    total_ct, total_mr = 0, 0

    for g in groups:
        gdir = os.path.join(root, g)
        if not os.path.isdir(gdir):
            warnings.warn(f"[pairs] group not found: {gdir}")
            continue

        for pdir in sorted(_list_subdirs(gdir)):
            ct_dir, mr_dir = _find_modality_dirs_patientwise(pdir)

            if ct_dir is None and mr_dir is None:
                imgs = _rglob_images(pdir)
                ct_imgs = [f for f in imgs if re.search(r'(^|/)(ct|ct_|\w*ct\w*)(/|_)', f.lower())]
                mr_imgs = [f for f in imgs if re.search(r'(^|/)(mri|b0|dwi)(/|_)', f.lower())]
                if not ct_imgs or not mr_imgs:
                    ct_candidates = []
                    mr_candidates = []
                    for f in imgs:
                        parts = f.lower().split(os.sep)
                        if any(re.search(r'(ct|ctax|axct)', part) for part in parts):
                            ct_candidates.append(f)
                        if any(re.search(r'(mri|b0|dwi)', part) for part in parts):
                            mr_candidates.append(f)
                    if not ct_imgs: ct_imgs = ct_candidates
                    if not mr_imgs: mr_imgs = mr_candidates
            else:
                ct_imgs = _rglob_images(ct_dir) if ct_dir else []
                mr_imgs = _rglob_images(mr_dir) if mr_dir else []

            total_ct += len(ct_imgs); total_mr += len(mr_imgs)
            if not ct_imgs or not mr_imgs:
                continue

            def _numkey(path: str) -> Tuple[str, int]:
                rel = os.path.relpath(path, pdir).lower()
                nums = re.findall(r'\d+', rel)
                num = int(nums[-1]) if nums else -1
                folder_hint = os.path.dirname(rel).split(os.sep)[0] if os.path.dirname(rel) else ""
                return (folder_hint, num)

            ct_sorted = sorted(ct_imgs, key=_numkey)
            mr_sorted = sorted(mr_imgs, key=_numkey)
            K = min(len(ct_sorted), len(mr_sorted))
            for i in range(K):
                pairs.append((ct_sorted[i], mr_sorted[i]))

    print(f"[pairs] patient-wise scan → CT files: {total_ct}, MR files: {total_mr}, matched pairs: {len(pairs)}")
    if not pairs:
        raise RuntimeError("No matched CT/MRI pairs found (patient-wise).")
    return pairs

class PairedCTMRI(Dataset):
    def __init__(self, cfg: Dict):
        super().__init__()
        self.cfg = cfg
        self.pairs = build_pairs_from_root(cfg)
        self.t = T.Compose([
            T.Resize((cfg["img_size"], cfg["img_size"]), interpolation=T.InterpolationMode.BICUBIC),
            T.ToTensor(),
            T.Normalize(mean=[0.5], std=[0.5])  # [-1,1]
        ])
    def __len__(self): return len(self.pairs)
    def __getitem__(self, idx):
        cpath, mpath = self.pairs[idx]
        ct  = Image.open(cpath).convert("L")
        mri = Image.open(mpath).convert("L")
        return {
            "ct_m11": self.t(ct),
            "mri_m11": self.t(mri),
            "ct_path": cpath,
            "mri_path": mpath
        }

# =========================
# 4) VAE (AutoencoderKL wrapper)
# =========================
class VAEWrapper(nn.Module):
    def __init__(self, encode_fn, decode_fn, scale=0.18215):
        super().__init__()
        self._enc = encode_fn
        self._dec = decode_fn
        self.scale = scale
    @torch.no_grad()
    def encode(self, x: torch.Tensor) -> torch.Tensor:
        return self._enc(x)
    @torch.no_grad()
    def decode(self, z: torch.Tensor) -> torch.Tensor:
        return self._dec(z)

def build_kl_vae_from_yaml(vae_config: str, vae_ckpt: str, scale: float, device: str, freeze=True, eval_mode=True) -> VAEWrapper:
    from omegaconf import OmegaConf
    from ldm.util import instantiate_from_config
    cfg = OmegaConf.load(vae_config)
    if "model" in cfg and "target" in cfg.model and "AutoencoderKL" in cfg.model.target:
        kl = instantiate_from_config(cfg.model)
    else:
        assert "model" in cfg and "params" in cfg.model and "first_stage_config" in cfg.model.params, "AutoencoderKL config not found"
        kl = instantiate_from_config(cfg.model.params.first_stage_config)

    kl.to(device)
    sd = torch.load(vae_ckpt, map_location="cpu"); sd = sd.get("state_dict", sd)
    kl.load_state_dict(sd, strict=False)
    if eval_mode: kl.eval()
    if freeze:
        for p in kl.parameters(): p.requires_grad_(False)

    @torch.no_grad()
    def _enc(x_m11):
        x = x_m11.repeat(1,3,1,1) if x_m11.size(1)==1 else x_m11
        posterior = kl.encode(x)
        return posterior.sample() * scale

    @torch.no_grad()
    def _dec(z):
        x = kl.decode(z / scale)
        return x.mean(1, keepdim=True) if x.size(1)==3 else x

    return VAEWrapper(_enc, _dec, scale=scale)

# =========================
# 5) Latent UNet & CT Cond
# =========================
class CTCondEncoder(nn.Module):
    def __init__(self, out_channels: int):
        super().__init__()
        self.net = nn.Sequential(
            nn.Conv2d(1, 32, 3,2,1), nn.SiLU(),
            nn.Conv2d(32, 64, 3,2,1), nn.SiLU(),
            nn.Conv2d(64, out_channels, 1,1,0)
        )
    def forward(self, x):
        return self.net(x)

def build_unet_from_cfg(cfg_latent: Dict, image_size: int, device: str):
    from ldm.modules.diffusionmodules.openaimodel import UNetModel
    in_channels  = cfg_latent["z_channels"] + cfg_latent["cond_channels"]
    out_channels = cfg_latent["z_channels"]
    net = UNetModel(
        image_size=image_size,
        in_channels=in_channels, out_channels=out_channels,
        model_channels=cfg_latent["model_channels"],
        num_res_blocks=cfg_latent["num_res_blocks"],
        channel_mult=tuple(cfg_latent["channel_mult"]),
        attention_resolutions=tuple(cfg_latent["attention_resolutions"]) if cfg_latent["attention_resolutions"] else (),
        num_heads=cfg_latent["num_heads"], num_head_channels=cfg_latent["num_head_channels"],
        num_heads_upsample=cfg_latent["num_heads_upsample"], dropout=cfg_latent["dropout"],
        use_scale_shift_norm=cfg_latent["use_scale_shift_norm"],
        use_checkpoint=cfg_latent["use_checkpoint"], use_fp16=cfg_latent["use_fp16"],
        resblock_updown=cfg_latent["resblock_updown"], use_new_attention_order=cfg_latent["use_new_attention_order"],
        use_spatial_transformer=cfg_latent["use_spatial_transformer"], transformer_depth=cfg_latent["transformer_depth"],
        context_dim=cfg_latent["context_dim"], n_embed=cfg_latent["n_embed"], legacy=cfg_latent["legacy"], dims=2
    )
    net.to(device)
    return net

def load_unet_weights_partial(unet: nn.Module, ckpt_path: str):
    sd = torch.load(ckpt_path, map_location="cpu"); state = sd.get("state_dict", sd)
    cleaned = {}
    for k, v in state.items():
        if k.startswith("model.diffusion_model."):
            cleaned[k.replace("model.diffusion_model.", "")] = v
        elif k.startswith("diffusion_model."):
            cleaned[k.replace("diffusion_model.", "")] = v
        elif ".diffusion_model." in k:
            cleaned[k.split(".diffusion_model.", 1)[1]] = v
    own = unet.state_dict()
    for k in list(cleaned.keys()):
        if k in own and isinstance(cleaned[k], torch.Tensor) and isinstance(own[k], torch.Tensor):
            wp, wc = cleaned[k], own[k]
            if wp.shape != wc.shape and wp.ndim == wc.ndim:
                slices = tuple(slice(0, min(a,b)) for a,b in zip(wp.shape, wc.shape))
                w_new = wc.clone()
                w_new[slices] = wp[slices]
                cleaned[k] = w_new
    missing, unexpected = unet.load_state_dict(cleaned, strict=False)
    if missing:    print(f"[UNet/partial] missing: {len(missing)}")
    if unexpected: print(f"[UNet/partial] unexpected: {len(unexpected)}")

# =========================
# 6) Diffusion schedule & q(z_t|z_0)
# =========================
@dataclass
class DiffusionSchedule:
    betas: torch.Tensor
    alphas: torch.Tensor
    alphas_cumprod: torch.Tensor
    alphas_cumprod_prev: torch.Tensor
    sqrt_alphas_cumprod: torch.Tensor
    sqrt_one_minus_alphas_cumprod: torch.Tensor
    posterior_variance: torch.Tensor

def build_schedule(num_steps: int, beta_schedule="cosine", device="cuda") -> DiffusionSchedule:
    from ldm.modules.diffusionmodules.util import make_beta_schedule
    betas = torch.from_numpy(make_beta_schedule(beta_schedule, num_steps)).float().to(device)
    alphas = 1.0 - betas
    a_bar = torch.cumprod(alphas, dim=0)
    a_bar_prev = torch.cat([torch.tensor([1.0], device=device), a_bar[:-1]], dim=0)
    return DiffusionSchedule(
        betas=betas, alphas=alphas,
        alphas_cumprod=a_bar, alphas_cumprod_prev=a_bar_prev,
        sqrt_alphas_cumprod=torch.sqrt(a_bar),
        sqrt_one_minus_alphas_cumprod=torch.sqrt(1.0 - a_bar),
        posterior_variance=betas * (1.0 - a_bar_prev) / (1.0 - a_bar)
    )

def q_sample_latent(z0, t, sched: DiffusionSchedule, noise=None):
    if noise is None: noise = torch.randn_like(z0)
    s_ab = sched.sqrt_alphas_cumprod[t].view(-1,1,1,1)
    s_om = sched.sqrt_one_minus_alphas_cumprod[t].view(-1,1,1,1)
    return s_ab * z0 + s_om * noise, noise

# =========================
# 7) Samplers (DDPM / DDIM) + 안전 어댑터
# =========================
@torch.no_grad()
def _ensure_input_for_unet(model, z, ct_cond):
    # 해상도 정렬
    if ct_cond.shape[-2:] != z.shape[-2:]:
        ct_cond = F.interpolate(ct_cond, size=z.shape[-2:], mode="bilinear", align_corners=False)
    x = torch.cat([z, ct_cond], 1)
    # 입력 채널 어댑터
    if hasattr(model, "in_channels") and x.shape[1] != model.in_channels:
        in_adapter = nn.Conv2d(x.shape[1], model.in_channels, 1, bias=True).to(x.device)
        nn.init.zeros_(in_adapter.weight); nn.init.zeros_(in_adapter.bias)
        keep = min(4, model.in_channels, in_adapter.in_channels)
        with torch.no_grad():
            for i in range(keep):
                in_adapter.weight[i, i, 0, 0] = 1.0
        x = in_adapter(x)
    return x

@torch.no_grad()
def _map_z_to_vae_channels(vae_wrap, z, ct_m11):
    # VAE 실제 z_channels 추정
    z_probe = vae_wrap.encode(ct_m11[:1])
    vae_zc = z_probe.shape[1]
    if z.shape[1] == vae_zc:
        return z
    # z→vae_zc 변환 어댑터
    adapter = nn.Conv2d(z.shape[1], vae_zc, kernel_size=1, bias=True).to(z.device)
    nn.init.zeros_(adapter.weight); nn.init.zeros_(adapter.bias)
    keep = min(z.shape[1], vae_zc, 4)
    with torch.no_grad():
        for i in range(keep):
            adapter.weight[i, i, 0, 0] = 1.0
    return adapter(z)

@torch.no_grad()
def sample_ddpm_latent(model, cond_enc, vae_wrap, ct_m11, sched: DiffusionSchedule, device="cuda"):
    B = ct_m11.size(0)
    ct_cond = cond_enc(ct_m11)
    # z 채널은 model.in_channels - cond_CH 가 기본 가정 (CFG 경로)
    z_ch = getattr(model, "in_channels", 5) - ct_cond.size(1)
    lat_h, lat_w = ct_cond.shape[-2], ct_cond.shape[-1]
    z = torch.randn(B, z_ch, lat_h, lat_w, device=device)
    T = sched.betas.size(0)
    for t in reversed(range(T)):
        t_b = torch.full((B,), t, device=device, dtype=torch.long)
        x = _ensure_input_for_unet(model, z, ct_cond)
        eps = model(x, t_b)
        a_bar = sched.alphas_cumprod[t]
        z0 = (z - torch.sqrt(1 - a_bar) * eps) / torch.sqrt(a_bar)
        mean = torch.sqrt(sched.alphas_cumprod_prev[t]) * z0 + torch.sqrt(1.0 - sched.alphas_cumprod_prev[t]) * eps
        z = mean + (torch.sqrt(sched.posterior_variance[t]) * torch.randn_like(z) if t>0 else 0)
    z = _map_z_to_vae_channels(vae_wrap, z, ct_m11)
    return vae_wrap.decode(z)

@torch.no_grad()
def sample_ddim_latent(model, cond_enc, vae_wrap, ct_m11, sched: DiffusionSchedule, ddim_steps=200, eta=0.0, device="cuda"):
    from ldm.modules.diffusionmodules.util import make_ddim_timesteps, make_ddim_sampling_parameters
    B = ct_m11.size(0)
    ct_cond = cond_enc(ct_m11)
    z_ch = getattr(model, "in_channels", 5) - ct_cond.size(1)
    lat_h, lat_w = ct_cond.shape[-2], ct_cond.shape[-1]
    z = torch.randn(B, z_ch, lat_h, lat_w, device=device)
    ts = np.array(make_ddim_timesteps('uniform', ddim_steps, sched.betas.size(0))) - 1
    sigmas, alphas, alphas_prev = make_ddim_sampling_parameters(sched.alphas_cumprod.detach().cpu().numpy(), ts, eta)
    sigmas = torch.from_numpy(sigmas).float().to(device)
    alphas = torch.from_numpy(alphas).float().to(device)
    alphas_prev = torch.from_numpy(alphas_prev).float().to(device)
    for i in reversed(range(len(ts))):
        t = int(ts[i]); t_b = torch.full((B,), t, device=device, dtype=torch.long)
        x = _ensure_input_for_unet(model, z, ct_cond)
        eps = model(x, t_b)
        a_t, a_prev, s_t = alphas[i], alphas_prev[i], sigmas[i]
        z0 = (z - torch.sqrt(1.0 - a_t) * eps) / torch.sqrt(a_t)
        dir_term = torch.sqrt(1.0 - a_prev - s_t**2) * eps
        noise = s_t * torch.randn_like(z) if i>0 else 0.0
        z = torch.sqrt(a_prev) * z0 + dir_term + noise
    z = _map_z_to_vae_channels(vae_wrap, z, ct_m11)
    return vae_wrap.decode(z)

# =========================
# 8) EMA
# =========================
class EMA:
    def __init__(self, model: nn.Module, decay=0.999):
        self.decay = decay; self.shadow = {}; self.backup = {}
        with torch.no_grad():
            for name, p in model.named_parameters():
                if p.requires_grad: self.shadow[name] = p.data.clone()
    def update(self, model: nn.Module):
        with torch.no_grad():
            for name, p in model.named_parameters():
                if p.requires_grad and name in self.shadow:
                    self.shadow[name] = self.decay * self.shadow[name] + (1.0 - self.decay) * p.data
    def apply_shadow(self, model: nn.Module):
        self.backup = {}
        with torch.no_grad():
            for name, p in model.named_parameters():
                if p.requires_grad and name in self.shadow:
                    self.backup[name] = p.data.clone(); p.data.copy_(self.shadow[name])
    def restore(self, model: nn.Module):
        with torch.no_grad():
            for name, p in model.named_parameters():
                if p.requires_grad and name in self.backup:
                    p.data.copy_(self.backup[name])
        self.backup = {}

# =========================
# 9) Build & Train / Inference
# =========================
def build_all_models(cfg: Dict):
    device = cfg["device"]
    assert VAE_CONFIG and os.path.isfile(VAE_CONFIG), "Set VAE_CONFIG path."
    assert VAE_CKPT   and os.path.isfile(VAE_CKPT),   "Set VAE_CKPT path."
    assert UNET_CKPT  and os.path.isfile(UNET_CKPT),  "Set UNET_CKPT path."

    vae_wrap = build_kl_vae_from_yaml(VAE_CONFIG, VAE_CKPT, scale=cfg["vae"]["scale"],
                                      device=device, freeze=cfg["vae"]["freeze"], eval_mode=cfg["vae"]["eval_mode"])

    cond_enc = CTCondEncoder(out_channels=cfg["latent_unet"]["cond_channels"]).to(device)

    # STRICT_PRETRAIN=False → CFG 기반
    from ldm.modules.diffusionmodules.openaimodel import UNetModel  # ensure import available
    unet = build_unet_from_cfg(cfg["latent_unet"], image_size=cfg["img_size"], device=device)
    load_unet_weights_partial(unet, UNET_CKPT)
    return vae_wrap, unet, cond_enc

@torch.no_grad()
def run_epoch_inference_ldm(unet, cond_enc, vae_wrap, sched, cfg, ds, device, epoch_idx=0):
    if not cfg["inference"]["enabled"]: return
    rng_state = torch.random.get_rng_state()
    if cfg["inference"]["seed"] is not None:
        torch.manual_seed(cfg["inference"]["seed"]); torch.cuda.manual_seed_all(cfg["inference"]["seed"])

    K = min(cfg["inference"]["num_examples"], len(ds))
    idxs = np.linspace(0, len(ds)-1, K).astype(int).tolist()
    ct_batch, stems_list, gt_paths = [], [], []
    for i in idxs:
        item = ds[i]
        ct_batch.append(item["ct_m11"])
        stems_list.append(stem(item["ct_path"]))
        gt_paths.append(item["mri_path"])
    ct_m11 = torch.stack(ct_batch, 0).to(device)

    if cfg["inference"]["sampler"].lower()=="ddpm":
        pred_m11 = sample_ddpm_latent(unet, cond_enc, vae_wrap, ct_m11, sched, device=device)
        tag = "ddpm"
    else:
        pred_m11 = sample_ddim_latent(unet, cond_enc, vae_wrap, ct_m11, sched,
                                      ddim_steps=cfg["inference"]["ddim_steps"], eta=cfg["inference"]["eta"], device=device)
        tag = f"ddim_eta{cfg['inference']['eta']:.1f}"

    outdir = os.path.join(cfg["save_dir"], cfg["inference"]["out_subdir"])
    os.makedirs(outdir, exist_ok=True)
    for i, s in enumerate(stems_list):
        img = to_image_from_m11(pred_m11[i])
        base = f"ep{epoch_idx:03d}_{s}_{tag}"
        img.save(os.path.join(outdir, f"{base}.png"))
        save_triptych(ct_m11[i], pred_m11[i], gt_paths[i],
                      os.path.join(outdir, f"{base}_triptych.png"),
                      size=cfg["img_size"])

    if cfg["inference"]["write_mapping"]:
        with open(os.path.join(outdir, f"ep{epoch_idx:03d}_mapping.txt"), "w") as f:
            for i, s in enumerate(stems_list):
                f.write(f"{s}\t{gt_paths[i]}\n")
    torch.random.set_rng_state(rng_state)

def train_coarse(cfg: Dict):
    set_seed(cfg["seed"])
    device = cfg["device"]
    os.makedirs(cfg["save_dir"], exist_ok=True)

    ds = PairedCTMRI(cfg)
    dl = DataLoader(ds, batch_size=cfg["batch_size"], shuffle=True,
                    num_workers=cfg["num_workers"], drop_last=True)

    vae_wrap, unet, cond_enc = build_all_models(cfg)
    unet.train(); cond_enc.train()
    opt_unet = torch.optim.AdamW(unet.parameters(), lr=cfg["lr"], betas=(0.9,0.999), weight_decay=1e-2)
    opt_cond = torch.optim.AdamW(cond_enc.parameters(), lr=cfg["lr"], betas=(0.9,0.999), weight_decay=1e-2)
    ema = EMA(unet, decay=cfg["ema_decay"])

    sched = build_schedule(cfg["num_timesteps"], beta_schedule=cfg["beta_schedule"], device=device)
    mse = nn.MSELoss()

    for epoch in range(cfg["epochs"]):
        t0 = time.time(); ep_loss=0.0
        for it,batch in enumerate(dl):
            ct_m11  = batch["ct_m11"].to(device)
            mri_m11 = batch["mri_m11"].to(device)

            with torch.no_grad():
                z0 = vae_wrap.encode(mri_m11)

            t = torch.randint(0, cfg["num_timesteps"], (ct_m11.size(0),), device=device).long()
            z_t, noise = q_sample_latent(z0, t, sched)          # z_t: [B, z_ch, H_l, W_l]
            ct_lat = cond_enc(ct_m11)                            # [B, cond_ch, H_c, W_c]

            # 해상도 정렬
            if ct_lat.shape[-2:] != z_t.shape[-2:]:
                ct_lat = F.interpolate(ct_lat, size=z_t.shape[-2:], mode="bilinear", align_corners=False)

            x_in = torch.cat([z_t, ct_lat], 1)                  # [B, z_ch+cond, H, W]

            # 입력 채널 어댑터 (UNet 기대 in_channels와 다르면)
            exp_in = getattr(unet, "in_channels", x_in.shape[1])
            if x_in.shape[1] != exp_in:
                adapter = getattr(train_coarse, "_chan_adapter", None)
                need_new = (
                    adapter is None
                    or adapter.in_channels != x_in.shape[1]
                    or adapter.out_channels != exp_in
                    or adapter.weight.device != x_in.device
                )
                if need_new:
                    adapter = nn.Conv2d(x_in.shape[1], exp_in, kernel_size=1, bias=True).to(x_in.device)
                    nn.init.zeros_(adapter.weight); nn.init.zeros_(adapter.bias)
                    keep = min(4, exp_in, adapter.in_channels)
                    with torch.no_grad():
                        for i in range(keep):
                            adapter.weight[i, i, 0, 0] = 1.0
                    train_coarse._chan_adapter = adapter
                x_in = adapter(x_in)

            eps_pred = unet(x_in, t)                            # [B, maybe != z_ch, H, W]

            # 출력 채널 어댑터: eps_pred → noise 채널 정렬
            if eps_pred.shape[1] != noise.shape[1]:
                out_adapter = getattr(train_coarse, "_out_adapter", None)
                need_new = (
                    out_adapter is None
                    or out_adapter.in_channels != eps_pred.shape[1]
                    or out_adapter.out_channels != noise.shape[1]
                    or out_adapter.weight.device != eps_pred.device
                )
                if need_new:
                    out_adapter = nn.Conv2d(eps_pred.shape[1], noise.shape[1], kernel_size=1, bias=True).to(eps_pred.device)
                    nn.init.zeros_(out_adapter.weight); nn.init.zeros_(out_adapter.bias)
                    keep = min(4, out_adapter.in_channels, out_adapter.out_channels)
                    with torch.no_grad():
                        for i in range(keep):
                            out_adapter.weight[i, i, 0, 0] = 1.0
                    train_coarse._out_adapter = out_adapter
                eps_pred = out_adapter(eps_pred)

            loss = mse(eps_pred, noise)

            if cfg["aux_losses"]["use_tv"]:
                with torch.no_grad():
                    a_bar = sched.alphas_cumprod[t].view(-1,1,1,1)
                    z0_hat = (z_t - torch.sqrt(1 - a_bar) * eps_pred) / torch.sqrt(a_bar)
                    x0_hat = vae_wrap.decode(z0_hat)
                tv = ( (x0_hat[:,:,1:,:]-x0_hat[:,:,:-1,:]).abs().mean() +
                       (x0_hat[:,:,:,1:]-x0_hat[:,:,:,:-1]).abs().mean() ) * cfg["aux_losses"]["tv_weight"]
                loss = loss + tv

            opt_unet.zero_grad(set_to_none=True)
            opt_cond.zero_grad(set_to_none=True)
            loss.backward()
            torch.nn.utils.clip_grad_norm_(unet.parameters(), 1.0)
            torch.nn.utils.clip_grad_norm_(cond_enc.parameters(), 1.0)
            opt_unet.step(); opt_cond.step()
            ema.update(unet)

            ep_loss += loss.item()
            if (it+1) % 50 == 0:
                print(f"[E{epoch+1:03d} I{it+1:05d}] loss={loss.item():.6f}")

        # 저장
        torch.save({
            "epoch": epoch,
            "unet": unet.state_dict(),
            "cond_enc": cond_enc.state_dict(),
            "opt_unet": opt_unet.state_dict(),
            "opt_cond": opt_cond.state_dict()
        }, os.path.join(cfg["save_dir"], f"coarse_epoch_{epoch:03d}.pt"))
        print(f"Epoch {epoch+1}/{cfg['epochs']}  avg loss: {ep_loss/len(dl):.6f}  |  {(time.time()-t0)/60.1:.1f} min")

        # 에폭 인퍼런스 (EMA 가중치)
        ema.apply_shadow(unet)
        try:
            run_epoch_inference_ldm(unet, cond_enc, vae_wrap, sched, cfg, ds, device, epoch_idx=epoch+1)
        finally:
            ema.restore(unet)

@torch.no_grad()
def sample_coarse(cfg: Dict, ckpt_path: Optional[str] = None):
    device = cfg["device"]
    os.makedirs(cfg["save_dir"], exist_ok=True)

    ds = PairedCTMRI(cfg)
    dl = DataLoader(ds, batch_size=cfg["batch_size"], shuffle=False,
                    num_workers=cfg["num_workers"], drop_last=False)

    vae_wrap, unet, cond_enc = build_all_models(cfg)
    unet.eval(); cond_enc.eval()

    if ckpt_path and os.path.isfile(ckpt_path):
        ck = torch.load(ckpt_path, map_location="cpu")
        unet.load_state_dict(ck["unet"], strict=False)
        cond_enc.load_state_dict(ck["cond_enc"], strict=False)
        print(f"[sample] loaded fine-tuned weights: {ckpt_path}")

    sched = build_schedule(cfg["num_timesteps"], beta_schedule=cfg["beta_schedule"], device=device)
    outdir = os.path.join(cfg["save_dir"], "coarse_samples"); os.makedirs(outdir, exist_ok=True)

    for it,batch in enumerate(dl):
        ct_m11  = batch["ct_m11"].to(device)
        mri_paths = batch["mri_path"]
        if cfg["inference"]["sampler"].lower()=="ddpm":
            pred_m11 = sample_ddpm_latent(unet, cond_enc, vae_wrap, ct_m11, sched, device=device)
            tag="ddpm"
        else:
            pred_m11 = sample_ddim_latent(unet, cond_enc, vae_wrap, ct_m11, sched,
                                          ddim_steps=cfg["inference"]["ddim_steps"], eta=cfg["inference"]["eta"], device=device)
            tag=f"ddim_eta{cfg['inference']['eta']:.1f}"
        for i in range(pred_m11.size(0)):
            s = stem(mri_paths[i])
            to_image_from_m11(pred_m11[i]).save(os.path.join(outdir, f"{s}_{tag}.png"))

# =========================
# 10) MAIN (플래그만 켜서 사용)
# =========================
RUN_TRAIN  = True  # True로 바꾸면 학습
RUN_SAMPLE = True  # True로 바꾸면 전체 샘플 저장

if RUN_TRAIN:
    assert VAE_CONFIG and os.path.isfile(VAE_CONFIG), "Set VAE_CONFIG"
    assert VAE_CKPT   and os.path.isfile(VAE_CKPT),   "Set VAE_CKPT"
    assert UNET_CKPT  and os.path.isfile(UNET_CKPT),  "Set UNET_CKPT"
    train_coarse(CFG)

if RUN_SAMPLE:
    ckpt_path = os.path.join(CFG["save_dir"], "coarse_epoch_049.pt")  # 예시
    assert VAE_CONFIG and os.path.isfile(VAE_CONFIG), "Set VAE_CONFIG"
    assert VAE_CKPT   and os.path.isfile(VAE_CKPT),   "Set VAE_CKPT"
    assert UNET_CKPT  and os.path.isfile(UNET_CKPT),  "Set UNET_CKPT"
    sample_coarse(CFG, ckpt_path=ckpt_path)


[pairs] patient-wise scan → CT files: 9533, MR files: 9533, matched pairs: 9533
making attention of type 'vanilla' with 512 in_channels
Working with z of shape (1, 3, 64, 64) = 12288 dimensions.
making attention of type 'vanilla' with 512 in_channels
loaded pretrained LPIPS loss from taming/modules/autoencoder/lpips/vgg.pth


/tmp/ipykernel_2743441/817311582.py:289: FutureWarning: You are using `torch.load` with `weights_only=False` (the current default value), which uses the default pickle module implicitly. It is possible to construct malicious pickle data which will execute arbitrary code during unpickling (See https://github.com/pytorch/pytorch/blob/main/SECURITY.md#untrusted-models for more details). In a future release, the default value for `weights_only` will be flipped to `True`. This limits the functions that could be executed during unpickling. Arbitrary objects will no longer be allowed to be loaded via this mode unless they are explicitly allowlisted by the user via `torch.serialization.add_safe_globals`. We recommend you start setting `weights_only=True` for any use case where you don't have full control of the loaded file. Please open an issue on GitHub for any issues related to this experimental feature.
  sd = torch.load(vae_ckpt, map_location="cpu"); sd = sd.get("state_dict", sd)
/tmp/ipyk

[UNet/partial] missing: 6
[UNet/partial] unexpected: 96
[E001 I00050] loss=0.298910
[E001 I00100] loss=0.373523
[E001 I00150] loss=0.140394
[E001 I00200] loss=0.334320
[E001 I00250] loss=0.197883
[E001 I00300] loss=0.189069
[E001 I00350] loss=0.184593
[E001 I00400] loss=0.103542
[E001 I00450] loss=0.145960
[E001 I00500] loss=0.130376
[E001 I00550] loss=0.093489
[E001 I00600] loss=0.035762
[E001 I00650] loss=0.125063
[E001 I00700] loss=0.076203
[E001 I00750] loss=0.247551
[E001 I00800] loss=0.083297
[E001 I00850] loss=0.054752
[E001 I00900] loss=0.097682
[E001 I00950] loss=0.096571
[E001 I01000] loss=0.259314
[E001 I01050] loss=0.085076
[E001 I01100] loss=0.094818
[E001 I01150] loss=0.099969
Epoch 1/50  avg loss: 0.164284  |  6.3 min
Selected timesteps for ddim sampler: [  1   6  11  16  21  26  31  36  41  46  51  56  61  66  71  76  81  86
  91  96 101 106 111 116 121 126 131 136 141 146 151 156 161 166 171 176
 181 186 191 196 201 206 211 216 221 226 231 236 241 246 251 256 261 266
 

/tmp/ipykernel_2743441/817311582.py:700: FutureWarning: You are using `torch.load` with `weights_only=False` (the current default value), which uses the default pickle module implicitly. It is possible to construct malicious pickle data which will execute arbitrary code during unpickling (See https://github.com/pytorch/pytorch/blob/main/SECURITY.md#untrusted-models for more details). In a future release, the default value for `weights_only` will be flipped to `True`. This limits the functions that could be executed during unpickling. Arbitrary objects will no longer be allowed to be loaded via this mode unless they are explicitly allowlisted by the user via `torch.serialization.add_safe_globals`. We recommend you start setting `weights_only=True` for any use case where you don't have full control of the loaded file. Please open an issue on GitHub for any issues related to this experimental feature.
  ck = torch.load(ckpt_path, map_location="cpu")


[sample] loaded fine-tuned weights: ./runs_ldm_coarse2/coarse_epoch_049.pt
Selected timesteps for ddim sampler: [  1   6  11  16  21  26  31  36  41  46  51  56  61  66  71  76  81  86
  91  96 101 106 111 116 121 126 131 136 141 146 151 156 161 166 171 176
 181 186 191 196 201 206 211 216 221 226 231 236 241 246 251 256 261 266
 271 276 281 286 291 296 301 306 311 316 321 326 331 336 341 346 351 356
 361 366 371 376 381 386 391 396 401 406 411 416 421 426 431 436 441 446
 451 456 461 466 471 476 481 486 491 496 501 506 511 516 521 526 531 536
 541 546 551 556 561 566 571 576 581 586 591 596 601 606 611 616 621 626
 631 636 641 646 651 656 661 666 671 676 681 686 691 696 701 706 711 716
 721 726 731 736 741 746 751 756 761 766 771 776 781 786 791 796 801 806
 811 816 821 826 831 836 841 846 851 856 861 866 871 876 881 886 891 896
 901 906 911 916 921 926 931 936 941 946 951 956 961 966 971 976 981 986
 991 996]
Selected alphas for ddim sampler: a_t: [9.99958694e-01 9.99679387e-01 9.992